# Fuego contra Fuego


Instalamos, cargamos y seteamos el entorno

In [1]:
%pip install optuna


Defaulting to user installation because normal site-packages is not writeable
Note: you may need to restart the kernel to use updated packages.


In [2]:
import pandas as pd
import numpy as np
import seaborn as sns
import matplotlib.pyplot as plt

from tqdm.notebook import tqdm

from sklearn.tree import DecisionTreeClassifier, plot_tree,  _tree
from sklearn.model_selection import train_test_split
from sklearn.model_selection import ShuffleSplit, StratifiedShuffleSplit
from sklearn.ensemble import RandomForestClassifier
from sklearn.impute import SimpleImputer

from joblib import Parallel, delayed

import optuna
from optuna.visualization import plot_optimization_history, plot_param_importances, plot_slice, plot_contour

from time import time

import pickle


/Users/manuelmarasco/Library/Python/3.9/lib/python/site-packages/tqdm/auto.py:21: TqdmWarning: IProgress not found. Please update jupyter and ipywidgets. See https://ipywidgets.readthedocs.io/en/stable/user_install.html
  from .autonotebook import tqdm as notebook_tqdm


In [3]:
base_path = '/Users/manuelmarasco/Library/CloudStorage/GoogleDrive-hola@manuelmarasco.com/Mi unidad/DMEyF/2026/notebooks/'
dataset_path = base_path + 'data/'
modelos_path = base_path + 'modelos/'
db_path = base_path + 'data/'
dataset_file = 'competencia_01.csv'

ganancia_acierto = 1_072_500
costo_estimulo = 27_500

mes_train = 202103
mes_test = 202105

# agregue sus semillas
semilla = 17
semillas = np.random.choice(1000000, size=50, replace=False).tolist()

data = pd.read_csv(dataset_path + dataset_file)

/var/folders/xn/fmllb0ws2fbdtxppprq7r2l00000gn/T/ipykernel_67726/2551575851.py:17: DtypeWarning: Columns (155) have mixed types. Specify dtype option on import or set low_memory=False.
  data = pd.read_csv(dataset_path + dataset_file)


Seguimos trabajando con Marzo como entrenamiento y Mayo como test.

In [4]:
X = data[data['foto_mes'] == mes_train]
y = X['clase_ternaria']
X = X.drop(columns=['clase_ternaria'])

In [5]:
X_futuro = data[data['foto_mes'] == mes_test]
y_futuro = X_futuro['clase_ternaria']
X_futuro = X_futuro.drop(columns=['clase_ternaria'])

Y variaremos la forma de la función de ganancia, para poder ser utilizada de una forma más genérica.

In [6]:
def ganancia_prob(y_hat, y, prop=1, class_index=1, threshold=0.025):
  @np.vectorize
  def ganancia_row(predicted, actual, threshold=0.025):
    return  (predicted >= threshold) * (ganancia_acierto if actual == "BAJA+2" else -costo_estimulo)

  return ganancia_row(y_hat[:,class_index], y).sum() / prop



Entrenemos y recordemos cuanto nos daba la ganancia en **Mayo**

Hablemos de ensemables, qué son?

* Un ensemble de modelos es una técnica donde se combinan múltiples modelos individuales para mejorar la precisión y robustez de las predicciones. La idea es que al combinar varios modelos, se pueden aprovechar las fortalezas de cada uno y reducir la posibilidad de errores que podría cometer un único modelo.

**Tipos de ensemble**:
 * **Bagging (Bootstrap Aggregating)**: Consiste en entrenar varios modelos base en diferentes subconjuntos del conjunto de datos de entrenamiento obtenidos mediante técnicas de remuestreo como el bootstrap y luego promediar sus predicciones. Ejemplo: **Random Forest**
 * **Boosting**: En esta técnica, los modelos se entrenan de manera secuencial. Cada modelo intenta corregir los errores cometidos por el modelo anterior. Ejemplo: AdaBoost y **Gradient Boosting**.
 * **Stacking**: En el stacking, se entrenan varios modelos y se combinan usando un "modelo meta". Las predicciones de los modelos base sirven como features para entrenar este modelo meta, que produce la predicción final.

* **Ventajas de usar ensemble de modelos**:
 * **Mejor rendimiento**: Al combinar modelos, generalmente se mejora la precisión en comparación con un solo modelo.
 * **Robustez**: Al integrar diferentes modelos, se mitiga el riesgo de que los errores de un modelo individual afecten gravemente la predicción final.




Pongamos foco en el **Random Forest**

Es un algoritmo de aprendizaje automático que funciona creando un conjunto de árboles de decisión. Para la creación de **árboles distintos** utiliza una técnica llamada bagging para crear múltiples subconjuntos del conjunto de datos de entrenamiento. Cada subconjunto se genera seleccionando al azar muestras del conjunto de datos original con reemplazo. No usa la totalidad de los datos de entrenamiento para cada conjunto. Los datos que quedan fueran son conocidos como **Out of Bag (oob)**

Para cada subconjunto, se construye un árbol de decisión. Sin embargo en cada nodo del árbol, **Random Forest** selecciona de forma aleatoria un grupo de variables y ajusta el árbol con esas variables. Este proceso ayuda a crear árboles que son menos correlacionados entre sí.

Cada árbol en el bosque se entrena de manera independiente usando su respectivo subconjunto de datos. Lueago, para una nueva observación, cada árbol realiza una predicción. El Random Forest luego combina las predicciones de todos los árboles para hacer una predicción final, devolviendo el promedio de las probabilidades de cada árbol individual.



Como desde la clase pasada solo personas más inteligentes, no vamos a empezar a probar **Random Forest** simples. Vamos a parametrizarlo desde el vamos.

Primero vamos a entender algunas limitaciones de la implementación:

El **Random Forest** no soporta nulos! Shame on you sklearn!.

Vamos a tener que imputar los datos. Discutamos entre todos forma de imputar los datos, mientras para salir del paso usamos la peor de todas.

In [7]:
imp_median = SimpleImputer(missing_values=np.nan, strategy='median')
Xi = imp_median.fit_transform(X)
Xif = imp_median.fit_transform(X_futuro)

Los parámetros que se pueden ajustar en el **rf** son

1. **n_estimators**: Número de árboles en el bosque.
2. **max_depth**: Profundidad máxima de los árboles.
3. **min_samples_split**: Número mínimo de muestras requeridas para dividir un nodo interno.
4. **min_samples_leaf**: Número mínimo de muestras requeridas para estar en un nodo hoja.
5. **max_features**: Número de features a usar en cada árbol. **sqrt** es una elección histórica.
6. **max_leaf_nodes**: Número máximo de nodos hoja en cada árbol.
7. **oob_score**: Indica si se usa la muestra fuera de bolsa (out-of-bag) para estimar la calidad del modelo. Para evitar hacer un **montecarlo-cross-validation** que se toma su tiempo, usaremos esta opción para buscar el mejor modelo. No es la mejor opción. Pero no es tan mala.
8. **n_jobs**: Siempre -1, para que use todos los cores presentes en 9. **max_samples**: Fracción de los samples.

Finalmente nuestra función de optimización queda la siguiente forma:

In [8]:
def objective(trial):
    max_depth = trial.suggest_int('max_depth', 2, 32)
    min_samples_split = trial.suggest_int('min_samples_split', 2, 2000)
    min_samples_leaf = trial.suggest_int('min_samples_leaf', 1, 200)
    max_features = trial.suggest_float('max_features', 0.05, 0.7)

    model = RandomForestClassifier(
        n_estimators=100,
        max_depth=max_depth,
        min_samples_split=min_samples_split,
        min_samples_leaf=min_samples_leaf,
        max_features=max_features,
        max_samples=0.7,
        random_state=semillas[0],
        n_jobs=-1,
        oob_score=True
    )

    model.fit(Xi, y)

    return ganancia_prob(model.oob_decision_function_, y)

storage_name = "sqlite:///" + db_path + "optimization_rf.db"
study_name = "exp_401_random-forest-opt"

study = optuna.create_study(
    direction="maximize",
    study_name=study_name,
    storage=storage_name,
    load_if_exists=True,
)



[I 2026-09-13 19:35:21,575] Using an existing study with name 'exp_401_random-forest-opt' instead of creating a new one.


In [9]:
study.optimize(objective, n_trials=100)

[I 2026-09-13 19:35:39,602] Trial 543 finished with value: 339487500.0 and parameters: {'max_depth': 22, 'min_samples_split': 99, 'min_samples_leaf': 73, 'max_features': 0.35830533253911034}. Best is trial 233 with value: 356372500.0.
[I 2026-09-13 19:35:55,508] Trial 544 finished with value: 346115000.0 and parameters: {'max_depth': 22, 'min_samples_split': 131, 'min_samples_leaf': 79, 'max_features': 0.3727714546909506}. Best is trial 233 with value: 356372500.0.
[I 2026-09-13 19:36:12,870] Trial 545 finished with value: 339652500.0 and parameters: {'max_depth': 21, 'min_samples_split': 107, 'min_samples_leaf': 66, 'max_features': 0.37602372525951616}. Best is trial 233 with value: 356372500.0.
[I 2026-09-13 19:36:27,741] Trial 546 finished with value: 343035000.0 and parameters: {'max_depth': 20, 'min_samples_split': 33, 'min_samples_leaf': 74, 'max_features': 0.3607940053271006}. Best is trial 233 with value: 356372500.0.
[I 2026-09-13 19:36:42,898] Trial 547 finished with value: 3

Exploramos como fue la búsqueda de parámetros

In [10]:
optuna.visualization.plot_optimization_history(study)

In [11]:
plot_param_importances(study)

In [12]:
plot_slice(study)

In [13]:
plot_contour(study)

In [14]:
plot_contour(study, params=["max_depth", "min_samples_split"])

Ajustamos el mejor modelo a todo el conjunto de datos



In [15]:
model_rf = RandomForestClassifier(
        n_estimators=100,
        **study.best_params,
        max_samples=0.7,
        random_state=semillas[0],
        n_jobs=-1,
        oob_score=True
    )

model_rf.fit(Xi, y)


RandomForestClassifier(max_depth=15, max_features=0.6245837962050735,
                       max_samples=0.7, min_samples_leaf=53,
                       min_samples_split=339, n_jobs=-1, oob_score=True,
                       random_state=915272)

Guardamos el modelo, para no tener que optimizar cada vez que lo queramos usar.

In [16]:
filename = modelos_path + 'exp_206_random_forest_model_100.sav'
pickle.dump(model_rf, open(filename, 'wb'))


Y lo cargamos para utilizarlo

In [17]:
model_rf = pickle.load(open(filename, 'rb'))
model_rf

RandomForestClassifier(max_depth=15, max_features=0.6245837962050735,
                       max_samples=0.7, min_samples_leaf=53,
                       min_samples_split=339, n_jobs=-1, oob_score=True,
                       random_state=915272)

Ahora vamos medir su ganancia sobre el dataset de **Mayo**

In [18]:
y_pred_rf = model_rf.predict_proba(Xif)
ganancias_rf = ganancia_prob(y_pred_rf, y_futuro)
print(f"Ganancia de modelo RF: {ganancias_rf}")

Ganancia de modelo RF: 251322500.0


Frente a los 208.010.000 de mi mejor árbol es algo sustancialmente mejor.

Igualmente usamos poquitos estimadores. Tan solo unos 100. Suficientes como para que la optimización no tarde una eternidad, pero es muy poco. Deberíamos sumar unos cuantos más.

In [19]:
model_rf_1000 = RandomForestClassifier(
        n_estimators=1000,
        **study.best_params,
        max_samples=0.7,
        random_state=semillas[0],
        n_jobs=-1,
        oob_score=True
    )

model_rf_1000.fit(Xi, y)

filename_rf_1000 = modelos_path + 'exp_206_random_forest_model_1000.sav'
pickle.dump(model_rf, open(filename_rf_1000, 'wb'))


In [20]:
model_rf_1000 = pickle.load(open(filename_rf_1000, 'rb'))
model_rf_1000

RandomForestClassifier(max_depth=15, max_features=0.6245837962050735,
                       max_samples=0.7, min_samples_leaf=53,
                       min_samples_split=339, n_jobs=-1, oob_score=True,
                       random_state=915272)

Veamos si sumar 10 veces más estimadores tuvo algún efecto

In [21]:
y_pred_rf = model_rf_1000.predict_proba(Xif)
ganancias_rf = ganancia_prob(y_pred_rf, y_futuro)
print(f"Ganancia de modelo RF 1000: {ganancias_rf}")

Ganancia de modelo RF 1000: 251322500.0


Mejoró un poco! Cada peso vale.



Por último evaluamos cuales son las variables más importantes del modelo. ¿Habrá influido la imputación?

In [22]:
importances = model_rf.feature_importances_

features = X.columns
feat_importances = pd.DataFrame({'feature': features, 'importance': importances})
feat_importances = feat_importances.sort_values('importance', ascending=False)

feat_importances.head(25)


,feature,importance
107,ctrx_quarter,0.210955
22,mcuentas_saldo,0.086077
33,mprestamos_personales,0.064636
18,mcaja_ahorro,0.055850
11,mpasivos_margen,0.051428
16,mcuenta_corriente,0.039297
8,mrentabilidad_annual,0.035113
133,Visa_status,0.034925
99,ccajas_consultas,0.031512
21,cdescubierto_preacordado,0.029408


Vamos a hacer un par de experimentos, que pasa si sacamos la variable más importante?

In [23]:
most_important_feature = feat_importances.iloc[0]['feature']

X_df = pd.DataFrame(Xi, columns=X.columns)
X_futuro_df = pd.DataFrame(Xif, columns=X_futuro.columns)

X_no_best_feature = X_df.drop(columns=[most_important_feature])
X_futuro_no_best_feature = X_futuro_df.drop(columns=[most_important_feature])

model_rf_no_best_feature = RandomForestClassifier(
    n_estimators=100,
    **study.best_params,
    max_samples=0.7,
    random_state=semillas[0],
    n_jobs=-1,
    oob_score=True
)

print(f"Entrenando modelo RF sin '{most_important_feature}'...")
model_rf_no_best_feature.fit(X_no_best_feature, y)

y_pred_rf_no_best_feature = model_rf_no_best_feature.predict_proba(X_futuro_no_best_feature)

ganancia_rf_no_best_feature = ganancia_prob(y_pred_rf_no_best_feature, y_futuro)

print(f"Ganancia del modelo RF sin '{most_important_feature}': {ganancia_rf_no_best_feature}")
print(f"Ganancia del modelo RF original: {ganancias_rf}")

Entrenando modelo RF sin 'ctrx_quarter'...
Ganancia del modelo RF sin 'ctrx_quarter': 249562500.0
Ganancia del modelo RF original: 251322500.0


¿Qué paso? ¿Se ha derrumbado las ganancias frente a la ausencia del pilar de los árboles?

Una prueba más, que pasa si sumamos variables que son ruido puro.

In [24]:
X_df_from_Xi = pd.DataFrame(Xi, columns=X.columns)

np.random.seed(semilla)

random_features_train = pd.DataFrame({
    f'random_feature_{i}': np.random.rand(len(X_df_from_Xi)) for i in range(1, 6)
})

X_with_random_features = pd.concat([X_df_from_Xi, random_features_train], axis=1)

model_rf_new_features = RandomForestClassifier(
    n_estimators=100,
    **study.best_params,
    max_samples=0.7,
    random_state=semillas[0],
    n_jobs=-1,
    oob_score=True
)

model_rf_new_features.fit(X_with_random_features, y)

importances_new_features = model_rf_new_features.feature_importances_

features_new_features = X_with_random_features.columns
feat_importances_new_features = pd.DataFrame({'feature': features_new_features, 'importance': importances_new_features})
feat_importances_new_features = feat_importances_new_features.sort_values('importance', ascending=False)

display(feat_importances_new_features.head(25))

,feature,importance
107,ctrx_quarter,0.228413
22,mcuentas_saldo,0.093924
33,mprestamos_personales,0.061307
11,mpasivos_margen,0.046242
18,mcaja_ahorro,0.044141
99,ccajas_consultas,0.035607
21,cdescubierto_preacordado,0.035200
16,mcuenta_corriente,0.032321
8,mrentabilidad_annual,0.030988
133,Visa_status,0.030709


Y una más, cual es el área bajo la curva en train?

In [25]:
from sklearn.metrics import roc_auc_score

y_pred_rf_train = model_rf_1000.predict_proba(Xi)

ganancia_rf_train = ganancia_prob(y_pred_rf_train, y)
print(f"Ganancia en el conjunto de entrenamiento: {ganancia_rf_train}")
print(f"Ganancia en el conjunto de Mayo: {ganancias_rf}")

y_train_numeric = (y == 'BAJA+2').astype(int)
y_futuro_numeric = (y_futuro == 'BAJA+2').astype(int)

auc_train = roc_auc_score(y_train_numeric, y_pred_rf_train[:, 1])
print(f"Área bajo la curva (AUC) en el conjunto de entrenamiento: {auc_train}")

auc_mayo = roc_auc_score(y_futuro_numeric, y_pred_rf[:, 1])
print(f"Área bajo la curva (AUC) en el conjunto de Mayo: {auc_mayo}")

Ganancia en el conjunto de entrenamiento: 485100000.0
Ganancia en el conjunto de Mayo: 251322500.0
Área bajo la curva (AUC) en el conjunto de entrenamiento: 0.9558044710489482
Área bajo la curva (AUC) en el conjunto de Mayo: 0.8825384808179099


Cuanta diferencia entre conjuntos. Seguramente debemos descartar este algoritmo, ¿o no?

Pregunta:
* **¿Cómo sabe que un random forest es superior a otro?**
* **¿Cómo supera el random forest presentado?**

## Tarea:

* Mejore la parametrización del **rf**


In [26]:
import os

bitacora_path = base_path + 'bitacora_experimentos_rf.csv'

def log_resultados(etapa, resultados_dict, params_dict=None):
    params_dict = params_dict or {}
    filas = []
    for nombre, ganancia in resultados_dict.items():
        filas.append({
            'timestamp': pd.Timestamp.now(),
            'etapa': etapa,
            'variante': nombre,
            'ganancia_mayo': ganancia,
            'params': str(params_dict.get(nombre, '')),
        })
    df_nuevo = pd.DataFrame(filas)
    existe = os.path.exists(bitacora_path)
    df_nuevo.to_csv(bitacora_path, mode='a', header=not existe, index=False)
    return df_nuevo

### Investigando mejoras a la parametrización

Vamos a probar un par de cambios candidatos por separado y después combinados, siempre midiendo la ganancia real sobre **Mayo** (no OOB, que es solo un proxy).

1. Actualizar a los `best_params` actuales del estudio de Optuna (puede haber corrido más trials desde la última vez que se fiteó el modelo).
2. Sumar `criterion="entropy"` en vez del `"gini"` por default.
3. Combinar ambos cambios.

In [27]:
# Candidato 1: cambiar el criterion de "gini" (default) a "entropy"
# Todo lo demas queda igual que el modelo baseline (model_rf_1000)

model_entropy = RandomForestClassifier(
    n_estimators=1000,
    **study.best_params,
    criterion="entropy",
    max_samples=0.7,
    random_state=semillas[0],
    n_jobs=-1,
    oob_score=True
)
model_entropy.fit(Xi, y)

ganancia_entropy = ganancia_prob(model_entropy.predict_proba(Xif), y_futuro)

print(f"Ganancia con criterion='entropy': {ganancia_entropy:,.0f}")
print(f"Ganancia baseline (criterion='gini'): {ganancias_rf:,.0f}")

Ganancia con criterion='entropy': 253,412,500
Ganancia baseline (criterion='gini'): 251,322,500


In [28]:
# Candidato 2: cambiar max_samples de 0.7 (fijo en todo el notebook, nunca tuneado) a 0.5
# Todo lo demas queda igual que el modelo baseline (model_rf_1000)

model_maxsamples = RandomForestClassifier(
    n_estimators=1000,
    **study.best_params,
    criterion="gini",
    max_samples=0.5,
    random_state=semillas[0],
    n_jobs=-1,
    oob_score=True
)
model_maxsamples.fit(Xi, y)

ganancia_maxsamples = ganancia_prob(model_maxsamples.predict_proba(Xif), y_futuro)

print(f"Ganancia con max_samples=0.5: {ganancia_maxsamples:,.0f}")
print(f"Ganancia baseline (max_samples=0.7): {ganancias_rf:,.0f}")

Ganancia con max_samples=0.5: 253,770,000
Ganancia baseline (max_samples=0.7): 251,322,500


In [29]:
# Candidato 3: combinar los dos cambios anteriores (entropy + max_samples=0.5) juntos

model_combinado = RandomForestClassifier(
    n_estimators=1000,
    **study.best_params,
    criterion="entropy",
    max_samples=0.5,
    random_state=semillas[0],
    n_jobs=-1,
    oob_score=True
)
model_combinado.fit(Xi, y)

ganancia_combinado = ganancia_prob(model_combinado.predict_proba(Xif), y_futuro)

print(f"Ganancia combinado (entropy + max_samples=0.5): {ganancia_combinado:,.0f}")

Ganancia combinado (entropy + max_samples=0.5): 246,592,500


In [30]:
# Comparacion de las 4 corridas de esta seccion, una al lado de la otra

print(f"baseline (gini, max_samples=0.7):        {ganancias_rf:,.0f}")
print(f"criterion=entropy:                        {ganancia_entropy:,.0f}")
print(f"max_samples=0.5:                           {ganancia_maxsamples:,.0f}")
print(f"combinado (entropy + max_samples=0.5):     {ganancia_combinado:,.0f}")

log_resultados('criterion_maxsamples', {
    'baseline': ganancias_rf,
    'criterion=entropy': ganancia_entropy,
    'max_samples=0.5': ganancia_maxsamples,
    'combinado (entropy + max_samples=0.5)': ganancia_combinado,
})

baseline (gini, max_samples=0.7):        251,322,500
criterion=entropy:                        253,412,500
max_samples=0.5:                           253,770,000
combinado (entropy + max_samples=0.5):     246,592,500


,timestamp,etapa,variante,ganancia_mayo,params
0,2026-09-13 20:19:11.556087,criterion_maxsamples,baseline,251322500.0,
1,2026-09-13 20:19:11.557102,criterion_maxsamples,criterion=entropy,253412500.0,
2,2026-09-13 20:19:11.557107,criterion_maxsamples,max_samples=0.5,253770000.0,
3,2026-09-13 20:19:11.557108,criterion_maxsamples,combinado (entropy + max_samples=0.5),246592500.0,


### Segunda ronda: escala logarítmica + múltiples semillas

Dos cambios más al espacio de búsqueda, probados solos y combinados:

1. **Escala logarítmica** en `min_samples_split` (2 a 2000) y `min_samples_leaf` (1 a 200): al ser rangos tan amplios, la escala lineal desperdicia trials explorando valores grandes donde el efecto es chico.
2. **Múltiples semillas**: en vez de medir la ganancia OOB con una sola `random_state`, promediamos sobre varias semillas para que el `objective` sea menos ruidoso (menos "sobreajustado" a una semilla en particular).

**Importante:** no podemos reusar el estudio `exp_401_random-forest-opt` para la variante log-scale — Optuna guarda la distribución de cada parámetro junto con cada trial, y `min_samples_split`/`min_samples_leaf` ya están grabados ahí con distribución lineal. Si le pedimos `log=True` sobre el mismo `study_name`, tira `ValueError` por incompatibilidad de distribución en el primer trial nuevo. Por eso cada variante que cambia la distribución necesita su propio `study_name` (mismo `.db`, no hace falta borrar nada de lo ya entrenado).

Para la variante "solo multi-semilla" sí podemos reusar `exp_401_random-forest-opt-multiseed`, que ya existe con 5 trials y la misma distribución lineal de siempre.

In [31]:
# Variante 1: SOLO escala logaritmica (misma semilla unica que el estudio original)
# Nueva study_name porque min_samples_split/leaf ya estan grabados con distribucion lineal en el estudio original

def objective_logscale(trial):
    max_depth = trial.suggest_int('max_depth', 2, 32)
    min_samples_split = trial.suggest_int('min_samples_split', 2, 2000, log=True)
    min_samples_leaf = trial.suggest_int('min_samples_leaf', 1, 200, log=True)
    max_features = trial.suggest_float('max_features', 0.05, 0.7)

    model = RandomForestClassifier(
        n_estimators=100,
        max_depth=max_depth,
        min_samples_split=min_samples_split,
        min_samples_leaf=min_samples_leaf,
        max_features=max_features,
        max_samples=0.7,
        random_state=semillas[0],
        n_jobs=-1,
        oob_score=True
    )
    model.fit(Xi, y)

    return ganancia_prob(model.oob_decision_function_, y)

study_logscale = optuna.create_study(
    direction="maximize",
    study_name="exp_401_random-forest-opt-logscale",
    storage=storage_name,
    load_if_exists=True,
)
study_logscale.optimize(objective_logscale, n_trials=50)

print(f"Mejor ganancia OOB (logscale): {study_logscale.best_value:,.0f}")
print(f"Mejores params: {study_logscale.best_params}")

[I 2026-09-13 20:19:11,585] A new study created in RDB with name: exp_401_random-forest-opt-logscale
[I 2026-09-13 20:19:26,361] Trial 0 finished with value: 338222500.0 and parameters: {'max_depth': 7, 'min_samples_split': 44, 'min_samples_leaf': 186, 'max_features': 0.6907564412410231}. Best is trial 0 with value: 338222500.0.
[I 2026-09-13 20:19:29,083] Trial 1 finished with value: 302197500.0 and parameters: {'max_depth': 22, 'min_samples_split': 5, 'min_samples_leaf': 157, 'max_features': 0.050627358799441954}. Best is trial 0 with value: 338222500.0.
[I 2026-09-13 20:19:54,254] Trial 2 finished with value: 332172500.0 and parameters: {'max_depth': 29, 'min_samples_split': 2, 'min_samples_leaf': 111, 'max_features': 0.6451867339202046}. Best is trial 0 with value: 338222500.0.
[I 2026-09-13 20:20:08,454] Trial 3 finished with value: 279482500.0 and parameters: {'max_depth': 22, 'min_samples_split': 161, 'min_samples_leaf': 1, 'max_features': 0.25758271883605893}. Best is trial 0 w

Mejor ganancia OOB (logscale): 350,460,000
Mejores params: {'max_depth': 18, 'min_samples_split': 665, 'min_samples_leaf': 87, 'max_features': 0.4993691138259325}


In [32]:
# Variante 2: SOLO multi-semilla (escala lineal, igual al estudio original), promediando 5 semillas por trial
# Reusamos el estudio "exp_401_random-forest-opt-multiseed" que ya existia con 5 trials (misma distribucion lineal)

def objective_multiseed(trial):
    max_depth = trial.suggest_int('max_depth', 2, 32)
    min_samples_split = trial.suggest_int('min_samples_split', 2, 2000)
    min_samples_leaf = trial.suggest_int('min_samples_leaf', 1, 200)
    max_features = trial.suggest_float('max_features', 0.05, 0.7)

    ganancias_oob = []
    for seed in semillas[:5]:
        model = RandomForestClassifier(
            n_estimators=100,
            max_depth=max_depth,
            min_samples_split=min_samples_split,
            min_samples_leaf=min_samples_leaf,
            max_features=max_features,
            max_samples=0.7,
            random_state=seed,
            n_jobs=-1,
            oob_score=True
        )
        model.fit(Xi, y)
        ganancias_oob.append(ganancia_prob(model.oob_decision_function_, y))

    return sum(ganancias_oob) / len(ganancias_oob)

study_multiseed = optuna.create_study(
    direction="maximize",
    study_name="exp_401_random-forest-opt-multiseed",
    storage=storage_name,
    load_if_exists=True,
)
study_multiseed.optimize(objective_multiseed, n_trials=50)

print(f"Mejor ganancia OOB (multiseed): {study_multiseed.best_value:,.0f}")
print(f"Mejores params: {study_multiseed.best_params}")

[I 2026-09-13 20:34:08,945] Using an existing study with name 'exp_401_random-forest-opt-multiseed' instead of creating a new one.
[I 2026-09-13 20:36:10,728] Trial 5 finished with value: 312950000.0 and parameters: {'max_depth': 31, 'min_samples_split': 1679, 'min_samples_leaf': 80, 'max_features': 0.6382430816278502}. Best is trial 0 with value: 342540000.0.
[I 2026-09-13 20:36:34,223] Trial 6 finished with value: 288590500.0 and parameters: {'max_depth': 25, 'min_samples_split': 1481, 'min_samples_leaf': 124, 'max_features': 0.1276945578719452}. Best is trial 0 with value: 342540000.0.
[I 2026-09-13 20:38:32,988] Trial 7 finished with value: 314237000.0 and parameters: {'max_depth': 30, 'min_samples_split': 1634, 'min_samples_leaf': 162, 'max_features': 0.6939863337646001}. Best is trial 0 with value: 342540000.0.
[I 2026-09-13 20:40:05,109] Trial 8 finished with value: 339273000.0 and parameters: {'max_depth': 15, 'min_samples_split': 99, 'min_samples_leaf': 147, 'max_features': 0.

Mejor ganancia OOB (multiseed): 345,939,000
Mejores params: {'max_depth': 17, 'min_samples_split': 382, 'min_samples_leaf': 94, 'max_features': 0.2978377124377754}


In [34]:
# Variante 3: escala logaritmica + multi-semilla, COMBINADOS
# Nueva study_name (distribucion log, no existia antes)

def objective_logscale_multiseed(trial):
    max_depth = trial.suggest_int('max_depth', 2, 32)
    min_samples_split = trial.suggest_int('min_samples_split', 2, 2000, log=True)
    min_samples_leaf = trial.suggest_int('min_samples_leaf', 1, 200, log=True)
    max_features = trial.suggest_float('max_features', 0.05, 0.7)

    ganancias_oob = []
    for seed in semillas[:5]:
        model = RandomForestClassifier(
            n_estimators=100,
            max_depth=max_depth,
            min_samples_split=min_samples_split,
            min_samples_leaf=min_samples_leaf,
            max_features=max_features,
            max_samples=0.7,
            random_state=seed,
            n_jobs=-1,
            oob_score=True
        )
        model.fit(Xi, y)
        ganancias_oob.append(ganancia_prob(model.oob_decision_function_, y))

    return sum(ganancias_oob) / len(ganancias_oob)

study_logscale_multiseed = optuna.create_study(
    direction="maximize",
    study_name="exp_401_random-forest-opt-logscale-multiseed",
    storage=storage_name,
    load_if_exists=True,
)
study_logscale_multiseed.optimize(objective_logscale_multiseed, n_trials=50)

print(f"Mejor ganancia OOB (logscale + multiseed): {study_logscale_multiseed.best_value:,.0f}")
print(f"Mejores params: {study_logscale_multiseed.best_params}")

[I 2026-09-14 09:08:16,149] Using an existing study with name 'exp_401_random-forest-opt-logscale-multiseed' instead of creating a new one.
[I 2026-09-14 09:10:30,276] Trial 12 finished with value: 338167500.0 and parameters: {'max_depth': 16, 'min_samples_split': 2, 'min_samples_leaf': 173, 'max_features': 0.6912634025144141}. Best is trial 10 with value: 344267000.0.
[I 2026-09-14 09:12:41,806] Trial 13 finished with value: 342342000.0 and parameters: {'max_depth': 17, 'min_samples_split': 2, 'min_samples_leaf': 184, 'max_features': 0.6983658079368054}. Best is trial 10 with value: 344267000.0.
[I 2026-09-14 09:15:06,963] Trial 14 finished with value: 310002000.0 and parameters: {'max_depth': 17, 'min_samples_split': 2, 'min_samples_leaf': 12, 'max_features': 0.5813949394261786}. Best is trial 10 with value: 344267000.0.
[I 2026-09-14 09:16:50,397] Trial 15 finished with value: 342386000.0 and parameters: {'max_depth': 12, 'min_samples_split': 4, 'min_samples_leaf': 83, 'max_features

Mejor ganancia OOB (logscale + multiseed): 347,044,500
Mejores params: {'max_depth': 12, 'min_samples_split': 11, 'min_samples_leaf': 46, 'max_features': 0.46403717992624216}


In [35]:
# Fiteamos el mejor modelo de cada una de las 3 variantes y medimos la ganancia real en Mayo

model_v_logscale = RandomForestClassifier(
    n_estimators=1000,
    **study_logscale.best_params,
    max_samples=0.7,
    random_state=semillas[0],
    n_jobs=-1,
    oob_score=True
)
model_v_logscale.fit(Xi, y)
ganancia_v_logscale = ganancia_prob(model_v_logscale.predict_proba(Xif), y_futuro)

model_v_multiseed = RandomForestClassifier(
    n_estimators=1000,
    **study_multiseed.best_params,
    max_samples=0.7,
    random_state=semillas[0],
    n_jobs=-1,
    oob_score=True
)
model_v_multiseed.fit(Xi, y)
ganancia_v_multiseed = ganancia_prob(model_v_multiseed.predict_proba(Xif), y_futuro)

model_v_logscale_multiseed = RandomForestClassifier(
    n_estimators=1000,
    **study_logscale_multiseed.best_params,
    max_samples=0.7,
    random_state=semillas[0],
    n_jobs=-1,
    oob_score=True
)
model_v_logscale_multiseed.fit(Xi, y)
ganancia_v_logscale_multiseed = ganancia_prob(model_v_logscale_multiseed.predict_proba(Xif), y_futuro)

print(f"baseline:                    {ganancias_rf:,.0f}")
print(f"logscale:                    {ganancia_v_logscale:,.0f}")
print(f"multiseed:                   {ganancia_v_multiseed:,.0f}")
print(f"logscale + multiseed:        {ganancia_v_logscale_multiseed:,.0f}")

log_resultados('logscale_multiseed', {
    'baseline': ganancias_rf,
    'logscale': ganancia_v_logscale,
    'multiseed': ganancia_v_multiseed,
    'logscale_multiseed': ganancia_v_logscale_multiseed,
}, {
    'logscale': study_logscale.best_params,
    'multiseed': study_multiseed.best_params,
    'logscale_multiseed': study_logscale_multiseed.best_params,
})

baseline:                    251,322,500
logscale:                    250,305,000
multiseed:                   258,582,500
logscale + multiseed:        251,762,500


,timestamp,etapa,variante,ganancia_mayo,params
0,2026-09-14 12:36:26.146227,logscale_multiseed,baseline,251322500.0,
1,2026-09-14 12:36:26.146302,logscale_multiseed,logscale,250305000.0,"{'max_depth': 18, 'min_samples_split': 665, 'm..."
2,2026-09-14 12:36:26.146307,logscale_multiseed,multiseed,258582500.0,"{'max_depth': 17, 'min_samples_split': 382, 'm..."
3,2026-09-14 12:36:26.146309,logscale_multiseed,logscale_multiseed,251762500.0,"{'max_depth': 12, 'min_samples_split': 11, 'mi..."


### Bitácora completa de experimentos

Todo lo corrido hasta ahora, sin importar cuántas veces reiniciaste el kernel o reescribiste una celda — cada corrida sumó filas nuevas al CSV, nunca se pisó nada.

In [36]:
bitacora = pd.read_csv(bitacora_path)
bitacora.sort_values('ganancia_mayo', ascending=False)

,timestamp,etapa,variante,ganancia_mayo,params
6,2026-09-14 12:36:26.146307,logscale_multiseed,multiseed,258582500.0,"{'max_depth': 17, 'min_samples_split': 382, 'm..."
2,2026-09-13 20:19:11.557107,criterion_maxsamples,max_samples=0.5,253770000.0,NaN
1,2026-09-13 20:19:11.557102,criterion_maxsamples,criterion=entropy,253412500.0,NaN
7,2026-09-14 12:36:26.146309,logscale_multiseed,logscale_multiseed,251762500.0,"{'max_depth': 12, 'min_samples_split': 11, 'mi..."
0,2026-09-13 20:19:11.556087,criterion_maxsamples,baseline,251322500.0,NaN
4,2026-09-14 12:36:26.146227,logscale_multiseed,baseline,251322500.0,NaN
5,2026-09-14 12:36:26.146302,logscale_multiseed,logscale,250305000.0,"{'max_depth': 18, 'min_samples_split': 665, 'm..."
3,2026-09-13 20:19:11.557108,criterion_maxsamples,combinado (entropy + max_samples=0.5),246592500.0,NaN
